# Image Captioning Explorer

Loads a random sample of images from a directory and generates captions using BLIP.

In [2]:
# Config - change these
IMAGE_DIR = r"C:\Users\jenni\Code\dATA"  # <-- set this to your image directory
SAMPLE_SIZE = 100
COLS = 3  # columns in the output grid

In [3]:
!pip install transformers torch pillow

'pip' is not recognized as an internal or external command,
operable program or batch file.


In [4]:
import random
from pathlib import Path

from PIL import Image
import matplotlib.pyplot as plt
import textwrap

from transformers import BlipProcessor, BlipForConditionalGeneration
import torch

In [5]:
# Gather all image files recursively
IMAGE_EXTENSIONS = {".jpg", ".jpeg", ".png", ".webp", ".bmp", ".tiff"}

all_images = [
    p for p in Path(IMAGE_DIR).rglob("*")
    if p.suffix.lower() in IMAGE_EXTENSIONS
]

print(f"Found {len(all_images)} images total")

sample = random.sample(all_images, min(SAMPLE_SIZE, len(all_images)))
print(f"Sampled {len(sample)} images")

Found 5599 images total
Sampled 100 images


In [6]:
# Load BLIP model
device = "cuda" if torch.cuda.is_available() else "cpu"
print(f"Using device: {device}")

processor = BlipProcessor.from_pretrained("Salesforce/blip-image-captioning-large")
model = BlipForConditionalGeneration.from_pretrained(
    "Salesforce/blip-image-captioning-large"
).to(device)

print("Model loaded!")

Using a slow image processor as `use_fast` is unset and a slow processor was saved with this model. `use_fast=True` will be the default behavior in v4.52, even if the model was saved with a slow processor. This will result in minor differences in outputs. You'll still be able to use a slow processor with `use_fast=False`.


Using device: cpu


preprocessor_config.json:   0%|          | 0.00/445 [00:00<?, ?B/s]

tokenizer_config.json:   0%|          | 0.00/527 [00:00<?, ?B/s]

vocab.txt: 0.00B [00:00, ?B/s]

...

Xet Storage is enabled for this repo, but the 'hf_xet' package is not installed. Falling back to regular HTTP download. For better performance, install the package with: `pip install huggingface_hub[hf_xet]` or `pip install hf_xet`


model.safetensors:   0%|          | 0.00/1.88G [00:00<?, ?B/s]

Error while downloading from https://huggingface.co/Salesforce/blip-image-captioning-large/resolve/main/model.safetensors: HTTPSConnectionPool(host='cas-bridge.xethub.hf.co', port=443): Read timed out.
Trying to resume download...


model.safetensors:  64%|######3   | 1.20G/1.88G [00:00<?, ?B/s]

Model loaded!


In [7]:
# Generate captions
results = []

for i, img_path in enumerate(sample):
    try:
        img = Image.open(img_path).convert("RGB")
        inputs = processor(img, return_tensors="pt").to(device)
        with torch.no_grad():
            output = model.generate(**inputs, max_new_tokens=50)
        caption = processor.decode(output[0], skip_special_tokens=True)
        results.append((img_path, img, caption))
    except Exception as e:
        print(f"Skipping {img_path.name}: {e}")
    
    if (i + 1) % 10 == 0:
        print(f"Processed {i + 1}/{len(sample)}")

print(f"\nDone! Captioned {len(results)} images.")

Skipping ._G_ModularCaves_UnderwaterSprings_MediumPuddle_01.jpg: cannot identify image file 'C:\\Users\\jenni\\Code\\dATA\\czepeku\\Modular Caves - $5 Rewards\\__MACOSX\\Modular Caves - $5 Rewards\\Tiles\\Gridded\\Underwater Springs\\._G_ModularCaves_UnderwaterSprings_MediumPuddle_01.jpg'
Skipping ._G_ModularCaves_Roots_02.jpg: cannot identify image file 'C:\\Users\\jenni\\Code\\dATA\\czepeku\\Modular Caves - $5 Rewards\\__MACOSX\\Modular Caves - $5 Rewards\\Tiles\\Gridded\\Mossy Caves\\._G_ModularCaves_Roots_02.jpg'
Processed 10/100
Skipping ._G_ModularCaves_CreatureCavern_CrushedSpider.jpg: cannot identify image file 'C:\\Users\\jenni\\Code\\dATA\\czepeku\\Modular Caves - $5 Rewards\\__MACOSX\\Modular Caves - $5 Rewards\\Tiles\\Gridded\\Creatures\\._G_ModularCaves_CreatureCavern_CrushedSpider.jpg'
Skipping ._ModularCaves_large columnar crystals.png: cannot identify image file 'C:\\Users\\jenni\\Code\\dATA\\czepeku\\Modular Caves - $5 Rewards\\__MACOSX\\Modular Caves - $5 Rewards\\Pro

c:\Users\jenni\Code\scene-atlas\.claude\worktrees\code-quality-backlog\.venv\Lib\site-packages\PIL\Image.py:3452: DecompressionBombWarning: Image size (106134000 pixels) exceeds limit of 89478485 pixels, could be decompression bomb DOS attack.
  warnings.warn(


Skipping ._AirshipsIII_JetEngine_BattleDrill_Pink.png: cannot identify image file 'C:\\Users\\jenni\\Code\\dATA\\czepeku\\Airships\\__MACOSX\\Airships Pt3 - $5 Rewards\\Jet Engine\\._AirshipsIII_JetEngine_BattleDrill_Pink.png'
Processed 50/100
Skipping ._ModularCaves_Column_Pieces_02.png: cannot identify image file 'C:\\Users\\jenni\\Code\\dATA\\czepeku\\Modular Caves - $5 Rewards\\__MACOSX\\Modular Caves - $5 Rewards\\Props\\._ModularCaves_Column_Pieces_02.png'
Skipping ._G_Inn_Indoors_Original_Night.jpg: cannot identify image file 'C:\\Users\\jenni\\Code\\dATA\\czepeku\\Ages of the Vale\\__MACOSX\\Ages of the Vale Pt.2 [27x39] - $5 Rewards (Gridded)\\01 Inn\\01 Inn Original\\._G_Inn_Indoors_Original_Night.jpg'
Skipping ._GL_ModularCaves_CrystalCaverns_CrystalCogs_01.jpg: cannot identify image file 'C:\\Users\\jenni\\Code\\dATA\\czepeku\\Modular Caves - $5 Rewards\\__MACOSX\\Modular Caves - $5 Rewards\\Tiles\\Gridless\\Crystal Caverns\\._GL_ModularCaves_CrystalCaverns_CrystalCogs_01.j

In [8]:
# Display results
rows = (len(results) + COLS - 1) // COLS
fig, axes = plt.subplots(rows, COLS, figsize=(6 * COLS, 7 * rows))
axes = axes.flatten() if rows > 1 else [axes] if COLS == 1 else axes.flatten()

for ax in axes:
    ax.axis("off")

for idx, (path, img, caption) in enumerate(results):
    ax = axes[idx]
    ax.imshow(img)
    wrapped = "\n".join(textwrap.wrap(caption, width=40))
    title = f"{path.name}\n{wrapped}"
    ax.set_title(title, fontsize=9, pad=8)
    ax.axis("off")

plt.tight_layout()
plt.show()